# Import

In [1]:
import pandas as pd
import json

from curation_tools.curation_tools import (
    CuratedDataset,
    ObsSchema,
    VarSchema,
    Experiment,
    download_file,
    upload_parquet_to_bq
)

import logging
logging.basicConfig(
    level=logging.INFO,
    format="%(asctime)s %(levelname)s %(name)s: %(message)s",
    handlers=[
        logging.FileHandler("curation.log"),
        logging.StreamHandler(),  # keep console output too
    ],
    force=True,
)
# show all columns
pd.set_option('display.max_columns', None)

/nfs/production/mfreeberg/perturb-seq/aleks/PerturbationCatalogue/.venv/lib/python3.12/site-packages/pandera/_pandas_deprecated.py:157: FutureWarning: Importing pandas-specific classes and functions from the
top-level pandera module will be **removed in a future version of pandera**.
If you're using pandera to validate pandas objects, we highly recommend updating
your import:

```
# old import
import pandera as pa

# new import
import pandera.pandas as pa
```

If you're using pandera to validate objects from other compatible libraries
like pyspark or polars, see the supported libraries section of the documentation
for more information on how to import pandera:

https://pandera.readthedocs.io/en/stable/supported_libraries.html

To disable this warning, set the environment variable:

```
export DISABLE_PANDERA_IMPORT_WARNING=True
```

  warnings.warn(_future_warning, FutureWarning)


# Download data

Download the data from AWS as such:

`!aws s3 cp --no-sign-request s3://genome-scale-tcell-perturb-seq/marson2025_data/{name_of_the_file}.h5ad ..aa/non_curated/h5ad/{name_of_the_file}.h5ad`


# Initialise the dataset object

In [2]:
noncurated_path = '../non_curated/h5ad/zhu_2025_D3_stim8hr_cl.h5ad'
cur_data = CuratedDataset(
    obs_schema=ObsSchema,
    var_schema=VarSchema,
    exp_metadata_schema=Experiment,
    noncurated_path=noncurated_path
)

cur_data.load_data()

Loading data from ../non_curated/h5ad/zhu_2025_D1_stim8hr_cl.h5ad


In [3]:
cur_data.adata.obs

,lane_id,n_genes_by_counts,total_counts,pct_counts_mt,top_guide_UMI_counts,guide_id,perturbed_gene_name,perturbed_gene_id,guide_type,PuroR,guide_group,low_quality
AAACAAGCAAACCGGTACTACTCA-1_CD4i_R1L13_CD4i_R1_D1_Stim8hr_CD4i_R1_Ultima,CD4i_R1L13,3983,8793.0,0.250199,100.0,NIPAL3-1,NIPAL3,ENSG00000001461,targeting,2.410379,targeting single sgRNA,False
AAACAAGCAAACGGTCAGTGAGTG-1_CD4i_R1L13_CD4i_R1_D1_Stim8hr_CD4i_R1_Ultima,CD4i_R1L13,2228,3720.0,0.053763,193.0,IL12RB2-2,IL12RB2,ENSG00000081985,targeting,2.687408,targeting single sgRNA,False
AAACAAGCAAATAACCACAGTCTG-1_CD4i_R1L13_CD4i_R1_D1_Stim8hr_CD4i_R1_Ultima,CD4i_R1L13,5695,19828.0,0.252169,NaN,NaN,NaN,NaN,NaN,0.000000,no sgRNA,False
AAACAAGCAAATAAGGAGTGAGTG-1_CD4i_R1L13_CD4i_R1_D1_Stim8hr_CD4i_R1_Ultima,CD4i_R1L13,4152,10349.0,0.057977,244.0,MCFD2-1,MCFD2,ENSG00000180398,targeting,2.757897,targeting single sgRNA,False
AAACAAGCAAATACCGACAGTCTG-1_CD4i_R1L13_CD4i_R1_D1_Stim8hr_CD4i_R1_Ultima,CD4i_R1L13,3925,8076.0,0.111441,55.0,ZFAND3-2,ZFAND3,ENSG00000156639,targeting,3.068036,targeting single sgRNA,False
...,...,...,...,...,...,...,...,...,...,...,...,...
TTTGTGAGTTGCACGCAGTGAGTG-1_CD4i_R1L14_CD4i_R1_D1_Stim8hr_CD4i_R1_Ultima,CD4i_R1L14,3347,6462.0,0.061900,85.0,ZNF397-2,ZNF397,ENSG00000186812,targeting,2.819059,targeting single sgRNA,False
TTTGTGAGTTGCCTGAACAGTCTG-1_CD4i_R1L14_CD4i_R1_D1_Stim8hr_CD4i_R1_Ultima,CD4i_R1L14,6689,32057.0,0.202764,63.0,multi_sgRNA,NaN,NaN,targeting,2.872419,multi sgRNA,False
TTTGTGAGTTGCGAAAACAGTCTG-1_CD4i_R1L14_CD4i_R1_D1_Stim8hr_CD4i_R1_Ultima,CD4i_R1L14,4904,14247.0,0.140380,51.0,PPM1A-1,PPM1A,ENSG00000100614,targeting,3.223942,targeting single sgRNA,False
TTTGTGAGTTGGCCACAGAGGCAA-1_CD4i_R1L14_CD4i_R1_D1_Stim8hr_CD4i_R1_Ultima,CD4i_R1L14,5840,20386.0,0.539586,56.0,LRTOMT-2,LRTOMT,ENSG00000284922,targeting,2.882643,targeting single sgRNA,False


In [4]:
cur_data.adata.var

,gene_ids,feature_types,genome,gene_name,mt
ENSG00000000003,ENSG00000000003,Gene Expression,GRCh38,TSPAN6,False
ENSG00000000005,ENSG00000000005,Gene Expression,GRCh38,TNMD,False
ENSG00000000419,ENSG00000000419,Gene Expression,GRCh38,DPM1,False
ENSG00000000457,ENSG00000000457,Gene Expression,GRCh38,SCYL3,False
ENSG00000000460,ENSG00000000460,Gene Expression,GRCh38,C1orf112,False
...,...,...,...,...,...
ENSG00000291122,ENSG00000291122,Gene Expression,GRCh38,CASTOR3P,False
ENSG00000291135,ENSG00000291135,Gene Expression,GRCh38,FCGR1BP,False
ENSG00000291145,ENSG00000291145,Gene Expression,GRCh38,PPP5D1P,False
ENSG00000291237,ENSG00000291237,Gene Expression,GRCh38,SOD2,False


# OBS slot curation

### Since for multi-guide perturbations the identities of said guides are unknown, we are filtering out these cells.

In [5]:
print(f"Number of cells before filtering: {cur_data.adata.n_obs}")
cur_data.adata = cur_data.adata[cur_data.adata.obs['guide_id'] != 'multi_sgRNA']
print(f"Number of cells after filtering: {cur_data.adata.n_obs}")

Number of cells before filtering: 2789727
Number of cells after filtering: 2176231


### Add `index` as `perturbation_name`

In [6]:
cur_data.adata.obs['cell_barcode'] = cur_data.adata.obs.index.str.split('_').str[0]
cur_data.adata.obs['perturbation_name'] = cur_data.adata.obs['cell_barcode'] +'_'+cur_data.adata.obs['lane_id'].astype(str)

/tmp/ipykernel_115074/2231587657.py:1: ImplicitModificationWarning: Trying to modify attribute `.obs` of view, initializing view as actual.
  cur_data.adata.obs['cell_barcode'] = cur_data.adata.obs.index.str.split('_').str[0]


### Show unique perturbations

In [7]:
cur_data.show_unique(slot = 'obs', column = 'perturbation_name')

Unique values in adata.obs.perturbation_name: 2176231
--------------------------------------------------
{'AAACAAGCAAACAAGAACAGTCTG-1_CD4i_R1L21',
 'AAACAAGCAAACAAGAACTACTCA-1_CD4i_R1L01',
 'AAACAAGCAAACAAGAAGTGAGTG-1_CD4i_R1L07',
 'AAACAAGCAAACAAGAAGTGAGTG-1_CD4i_R1L11',
 'AAACAAGCAAACAATCACTACTCA-1_CD4i_R1L17',
 'AAACAAGCAAACAATCAGAGGCAA-1_CD4i_R1L07',
 'AAACAAGCAAACAATCAGTGAGTG-1_CD4i_R1L04',
 'AAACAAGCAAACAATCAGTGAGTG-1_CD4i_R1L17',
 'AAACAAGCAAACACGCACAGTCTG-1_CD4i_R1L01',
 'AAACAAGCAAACACGCACAGTCTG-1_CD4i_R1L22',
 'AAACAAGCAAACACGCACTACTCA-1_CD4i_R1L18',
 'AAACAAGCAAACACGCACTACTCA-1_CD4i_R1L21',
 'AAACAAGCAAACACGCAGAGGCAA-1_CD4i_R1L05',
 'AAACAAGCAAACACGCAGAGGCAA-1_CD4i_R1L21',
 'AAACAAGCAAACACGCAGTGAGTG-1_CD4i_R1L19',
 'AAACAAGCAAACCCAAAGTGAGTG-1_CD4i_R1L20',
 'AAACAAGCAAACCGGTACAGTCTG-1_CD4i_R1L22',
 'AAACAAGCAAACCGGTACTACTCA-1_CD4i_R1L13',
 'AAACAAGCAAACCGGTAGAGGCAA-1_CD4i_R1L03',
 'AAACAAGCAAACCGGTAGAGGCAA-1_CD4i_R1L17',
 'AAACAAGCAAACCTGAACAGTCTG-1_CD4i_R1L01',
 'AAACAAGCAAA

IOPub data rate exceeded.
The Jupyter server will temporarily stop sending output
to the client in order to avoid crashing it.
To change this limit, set the config variable
`--ServerApp.iopub_data_rate_limit`.

Current values:
ServerApp.iopub_data_rate_limit=1000000.0 (bytes/sec)
ServerApp.rate_limit_window=3.0 (secs)



,
 'CATTTGGTCATGACCCACTACTCA-1_CD4i_R1L15',
 'CATTTGGTCATGACCCAGTGAGTG-1_CD4i_R1L14',
 'CATTTGGTCATGAGGTAGTGAGTG-1_CD4i_R1L07',
 'CATTTGGTCATGAGGTAGTGAGTG-1_CD4i_R1L23',
 'CATTTGGTCATGATGAACAGTCTG-1_CD4i_R1L09',
 'CATTTGGTCATGATGAAGAGGCAA-1_CD4i_R1L09',
 'CATTTGGTCATGCATTACTACTCA-1_CD4i_R1L16',
 'CATTTGGTCATGCATTAGAGGCAA-1_CD4i_R1L13',
 'CATTTGGTCATGCCTAACAGTCTG-1_CD4i_R1L19',
 'CATTTGGTCATGCCTAACAGTCTG-1_CD4i_R1L20',
 'CATTTGGTCATGCGGAAGAGGCAA-1_CD4i_R1L04',
 'CATTTGGTCATGCGGAAGAGGCAA-1_CD4i_R1L07',
 'CATTTGGTCATGCGTCACAGTCTG-1_CD4i_R1L23',
 'CATTTGGTCATGCGTCACTACTCA-1_CD4i_R1L09',
 'CATTTGGTCATGCGTCACTACTCA-1_CD4i_R1L20',
 'CATTTGGTCATGCGTCACTACTCA-1_CD4i_R1L21',
 'CATTTGGTCATGCGTCAGTGAGTG-1_CD4i_R1L21',
 'CATTTGGTCATGGAACACAGTCTG-1_CD4i_R1L05',
 'CATTTGGTCATGGAACACTACTCA-1_CD4i_R1L05',
 'CATTTGGTCATGGAACACTACTCA-1_CD4i_R1L06',
 'CATTTGGTCATGGATAACAGTCTG-1_CD4i_R1L09',
 'CATTTGGTCATGGATAAGAGGCAA-1_CD4i_R1L01',
 'CATTTGGTCATGGATAAGTGAGTG-1_CD4i_R1L20',
 'CATTTGGTCATGGTCCACTACTCA-1_CD4

IOPub data rate exceeded.
The Jupyter server will temporarily stop sending output
to the client in order to avoid crashing it.
To change this limit, set the config variable
`--ServerApp.iopub_data_rate_limit`.

Current values:
ServerApp.iopub_data_rate_limit=1000000.0 (bytes/sec)
ServerApp.rate_limit_window=3.0 (secs)



'CGCATGAAGAAGGTCTACTACTCA-1_CD4i_R1L15',
 'CGCATGAAGAAGGTCTACTACTCA-1_CD4i_R1L17',
 'CGCATGAAGAAGGTCTAGAGGCAA-1_CD4i_R1L17',
 'CGCATGAAGAAGGTTCAGAGGCAA-1_CD4i_R1L03',
 'CGCATGAAGAAGTACCACTACTCA-1_CD4i_R1L08',
 'CGCATGAAGAATGGCTACAGTCTG-1_CD4i_R1L08',
 'CGCATGAAGAATGGCTACAGTCTG-1_CD4i_R1L22',
 'CGCATGAAGAATGGCTACTACTCA-1_CD4i_R1L08',
 'CGCATGAAGAATGGCTACTACTCA-1_CD4i_R1L21',
 'CGCATGAAGAATGGCTACTACTCA-1_CD4i_R1L22',
 'CGCATGAAGAATGGCTAGAGGCAA-1_CD4i_R1L05',
 'CGCATGAAGAATGGCTAGAGGCAA-1_CD4i_R1L08',
 'CGCATGAAGAATGGGAACAGTCTG-1_CD4i_R1L06',
 'CGCATGAAGAATGGGAACAGTCTG-1_CD4i_R1L22',
 'CGCATGAAGAATGGGAACTACTCA-1_CD4i_R1L08',
 'CGCATGAAGAATGGGAAGAGGCAA-1_CD4i_R1L01',
 'CGCATGAAGAATGGGAAGAGGCAA-1_CD4i_R1L06',
 'CGCATGAAGAATGGGAAGTGAGTG-1_CD4i_R1L22',
 'CGCATGAAGACAAAGGACAGTCTG-1_CD4i_R1L08',
 'CGCATGAAGACAAAGGACAGTCTG-1_CD4i_R1L13',
 'CGCATGAAGACAAAGGACTACTCA-1_CD4i_R1L13',
 'CGCATGAAGACAAAGGAGAGGCAA-1_CD4i_R1L13',
 'CGCATGAAGACAACACACAGTCTG-1_CD4i_R1L18',
 'CGCATGAAGACAACACACAGTCTG-1_CD4i_R

...

'GTTCCAGGTCAATCGTAGAGGCAA-1_CD4i_R1L18',
 'GTTCCAGGTCAATCGTAGTGAGTG-1_CD4i_R1L07',
 'GTTCCAGGTCAATGTCACAGTCTG-1_CD4i_R1L04',
 'GTTCCAGGTCAATTCAACAGTCTG-1_CD4i_R1L21',
 'GTTCCAGGTCAATTGCACTACTCA-1_CD4i_R1L10',
 'GTTCCAGGTCAATTGCAGAGGCAA-1_CD4i_R1L03',
 'GTTCCAGGTCAATTGCAGAGGCAA-1_CD4i_R1L05',
 'GTTCCAGGTCAATTGCAGTGAGTG-1_CD4i_R1L10',
 'GTTCCAGGTCACACCAAGTGAGTG-1_CD4i_R1L03',
 'GTTCCAGGTCACAGAAAGAGGCAA-1_CD4i_R1L02',
 'GTTCCAGGTCACAGGGACAGTCTG-1_CD4i_R1L01',
 'GTTCCAGGTCACAGGGACAGTCTG-1_CD4i_R1L06',
 'GTTCCAGGTCACAGGGAGAGGCAA-1_CD4i_R1L12',
 'GTTCCAGGTCACAGGGAGAGGCAA-1_CD4i_R1L18',
 'GTTCCAGGTCACAGGGAGTGAGTG-1_CD4i_R1L21',
 'GTTCCAGGTCACCAGCACAGTCTG-1_CD4i_R1L10',
 'GTTCCAGGTCACCAGCACTACTCA-1_CD4i_R1L06',
 'GTTCCAGGTCACCAGCACTACTCA-1_CD4i_R1L10',
 'GTTCCAGGTCACCAGCAGAGGCAA-1_CD4i_R1L07',
 'GTTCCAGGTCACCAGCAGTGAGTG-1_CD4i_R1L06',
 'GTTCCAGGTCACCAGCAGTGAGTG-1_CD4i_R1L07',
 'GTTCCAGGTCACCAGCAGTGAGTG-1_CD4i_R1L22',
 'GTTCCAGGTCACGATTACTACTCA-1_CD4i_R1L20',
 'GTTCCAGGTCACTAGTAGTGAGTG-1_CD4i_R

IOPub data rate exceeded.
The Jupyter server will temporarily stop sending output
to the client in order to avoid crashing it.
To change this limit, set the config variable
`--ServerApp.iopub_data_rate_limit`.

Current values:
ServerApp.iopub_data_rate_limit=1000000.0 (bytes/sec)
ServerApp.rate_limit_window=3.0 (secs)



'TGCCCTGAGAAACTCAACAGTCTG-1_CD4i_R1L05',
 'TGCCCTGAGAAACTCAAGAGGCAA-1_CD4i_R1L01',
 'TGCCCTGAGAAACTCAAGAGGCAA-1_CD4i_R1L13',
 'TGCCCTGAGAAACTCAAGAGGCAA-1_CD4i_R1L21',
 'TGCCCTGAGAAACTCAAGTGAGTG-1_CD4i_R1L05',
 'TGCCCTGAGAAAGGCAAGTGAGTG-1_CD4i_R1L02',
 'TGCCCTGAGAACCTAAACAGTCTG-1_CD4i_R1L02',
 'TGCCCTGAGAACCTCCACTACTCA-1_CD4i_R1L17',
 'TGCCCTGAGAAGCAAGAGTGAGTG-1_CD4i_R1L08',
 'TGCCCTGAGAAGCATCACAGTCTG-1_CD4i_R1L19',
 'TGCCCTGAGAAGCATCACTACTCA-1_CD4i_R1L04',
 'TGCCCTGAGAAGCATCACTACTCA-1_CD4i_R1L13',
 'TGCCCTGAGAAGGTCTACAGTCTG-1_CD4i_R1L04',
 'TGCCCTGAGAAGGTCTACTACTCA-1_CD4i_R1L05',
 'TGCCCTGAGAAGGTCTAGAGGCAA-1_CD4i_R1L10',
 'TGCCCTGAGAAGGTCTAGTGAGTG-1_CD4i_R1L04',
 'TGCCCTGAGAAGGTCTAGTGAGTG-1_CD4i_R1L22',
 'TGCCCTGAGAAGGTTCACTACTCA-1_CD4i_R1L04',
 'TGCCCTGAGAAGGTTCACTACTCA-1_CD4i_R1L08',
 'TGCCCTGAGAAGGTTCAGAGGCAA-1_CD4i_R1L07',
 'TGCCCTGAGAAGTACCACTACTCA-1_CD4i_R1L02',
 'TGCCCTGAGAAGTAGGACAGTCTG-1_CD4i_R1L23',
 'TGCCCTGAGAAGTAGGACTACTCA-1_CD4i_R1L09',
 'TGCCCTGAGAAGTAGGAGTGAGTG-1_CD4i_R

IOPub data rate exceeded.
The Jupyter server will temporarily stop sending output
to the client in order to avoid crashing it.
To change this limit, set the config variable
`--ServerApp.iopub_data_rate_limit`.

Current values:
ServerApp.iopub_data_rate_limit=1000000.0 (bytes/sec)
ServerApp.rate_limit_window=3.0 (secs)



'TTTAACGGTAGCCACCACTACTCA-1_CD4i_R1L05',
 'TTTAACGGTAGCCATTACAGTCTG-1_CD4i_R1L01',
 'TTTAACGGTAGCCATTACAGTCTG-1_CD4i_R1L02',
 'TTTAACGGTAGCCATTAGAGGCAA-1_CD4i_R1L14',
 'TTTAACGGTAGCCATTAGAGGCAA-1_CD4i_R1L16',
 'TTTAACGGTAGCCATTAGTGAGTG-1_CD4i_R1L02',
 'TTTAACGGTAGCCATTAGTGAGTG-1_CD4i_R1L16',
 'TTTAACGGTAGCCCGTACAGTCTG-1_CD4i_R1L20',
 'TTTAACGGTAGCCCGTACTACTCA-1_CD4i_R1L12',
 'TTTAACGGTAGCCCGTACTACTCA-1_CD4i_R1L13',
 'TTTAACGGTAGCCCGTACTACTCA-1_CD4i_R1L20',
 'TTTAACGGTAGCCCGTAGAGGCAA-1_CD4i_R1L22',
 'TTTAACGGTAGCCCGTAGTGAGTG-1_CD4i_R1L01',
 'TTTAACGGTAGCCCGTAGTGAGTG-1_CD4i_R1L13',
 'TTTAACGGTAGCCTTGACAGTCTG-1_CD4i_R1L05',
 'TTTAACGGTAGCCTTGAGAGGCAA-1_CD4i_R1L11',
 'TTTAACGGTAGCCTTGAGAGGCAA-1_CD4i_R1L20',
 'TTTAACGGTAGCGCGAACTACTCA-1_CD4i_R1L15',
 'TTTAACGGTAGCGCGAAGAGGCAA-1_CD4i_R1L16',
 'TTTAACGGTAGCGCGAAGTGAGTG-1_CD4i_R1L16',
 'TTTAACGGTAGCGGATACTACTCA-1_CD4i_R1L15',
 'TTTAACGGTAGCTTGTACAGTCTG-1_CD4i_R1L02',
 'TTTAACGGTAGCTTGTACAGTCTG-1_CD4i_R1L22',
 'TTTAACGGTAGCTTGTACTACTCA-1_CD4i_R

### Add guide RNA information

In [8]:
# download the guide RNA spreadsheet
download_file(
    url="https://raw.githubusercontent.com/emdann/GWT_perturbseq_analysis_2025/refs/heads/master/metadata/suppl_tables/sgrna_library_metadata.suppl_table.csv",
    dest_path="../supplementary/zhu_2025_guide_info.csv"
)
# read in the guide RNA info csv
guide_info_df = pd.read_csv("../supplementary/zhu_2025_guide_info.csv")

guide_info_df = guide_info_df[['sgRNA', 'seq']]

guide_info_df['sgRNA'] = guide_info_df['sgRNA'].str.replace('1-Jun','JUN-1').str.replace('2-Jun','JUN-2')

guide_info_df = guide_info_df.rename(columns={'seq': 'guide_sequence', 'sgRNA':'guide_id'})

guide_info_df


File ../supplementary/zhu_2025_guide_info.csv already exists. Skipping download.


,guide_id,guide_sequence
0,ARMC5-1,CTGCCTCGCGCAGCTCGCGG
1,DDB1-1,GGAGTTCGCTGCGCGCTGTT
2,FNDC10-1,TGCCCGCTCCCCGCGATCCC
3,RORC-1,TCTGTGGGGCCCTGTCCATG
4,SLC35F6-1,GAACAGCTGGTACTTGGTCC
...,...,...
26499,NTC-988,TTTCAGGCTACGGGCGCGGG
26500,NTC-989,TTTCCCATGATCATTTAGTG
26501,NTC-990,TTTCGCCCAAGAGGCTTGGG
26502,NTC-991,TTTCGTGCCGATGTAACACA


In [9]:
print("Number of overlapping guides with cur_data:")
cur_data.adata.obs['guide_id'].isin(guide_info_df['guide_id'].to_list()).value_counts()

Number of overlapping guides with cur_data:


guide_id
True     1610529
False     565702
Name: count, dtype: int64

In [10]:
# merge cur_data.adata.obs with guide_info_df
cur_data.adata.obs = cur_data.adata.obs.merge(guide_info_df, on='guide_id', how='left')
# check that there are no missing guide sequences
print(f"Number of missing guide sequences: {cur_data.adata.obs['guide_sequence'].isna().sum()}")


/homes/zakirov/.local/share/uv/python/cpython-3.12.12-linux-x86_64-gnu/lib/python3.12/functools.py:912: ImplicitModificationWarning: Transforming to str index.
  return dispatch(args[0].__class__)(*args, **kw)


Number of missing guide sequences: 565702


In [11]:
cur_data.adata.obs

,lane_id,n_genes_by_counts,total_counts,pct_counts_mt,top_guide_UMI_counts,guide_id,perturbed_gene_name,perturbed_gene_id,guide_type,PuroR,guide_group,low_quality,cell_barcode,perturbation_name,guide_sequence
0,CD4i_R1L13,3983,8793.0,0.250199,100.0,NIPAL3-1,NIPAL3,ENSG00000001461,targeting,2.410379,targeting single sgRNA,False,AAACAAGCAAACCGGTACTACTCA-1,AAACAAGCAAACCGGTACTACTCA-1_CD4i_R1L13,GGACTCTTCGTGCAACCCGG
1,CD4i_R1L13,2228,3720.0,0.053763,193.0,IL12RB2-2,IL12RB2,ENSG00000081985,targeting,2.687408,targeting single sgRNA,False,AAACAAGCAAACGGTCAGTGAGTG-1,AAACAAGCAAACGGTCAGTGAGTG-1_CD4i_R1L13,GGCGGAGAGCGCGACACGTG
2,CD4i_R1L13,5695,19828.0,0.252169,NaN,NaN,NaN,NaN,NaN,0.000000,no sgRNA,False,AAACAAGCAAATAACCACAGTCTG-1,AAACAAGCAAATAACCACAGTCTG-1_CD4i_R1L13,NaN
3,CD4i_R1L13,4152,10349.0,0.057977,244.0,MCFD2-1,MCFD2,ENSG00000180398,targeting,2.757897,targeting single sgRNA,False,AAACAAGCAAATAAGGAGTGAGTG-1,AAACAAGCAAATAAGGAGTGAGTG-1_CD4i_R1L13,AGGAGCTGCTACAGCAGAGG
4,CD4i_R1L13,3925,8076.0,0.111441,55.0,ZFAND3-2,ZFAND3,ENSG00000156639,targeting,3.068036,targeting single sgRNA,False,AAACAAGCAAATACCGACAGTCTG-1,AAACAAGCAAATACCGACAGTCTG-1_CD4i_R1L13,GTTCCAGGCCGGTCAGCTGG
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
2176226,CD4i_R1L14,3637,7868.0,0.216065,74.0,DMRT1-2,DMRT1,ENSG00000137090,targeting,2.744874,targeting single sgRNA,False,TTTGTGAGTTGACCCAACAGTCTG-1,TTTGTGAGTTGACCCAACAGTCTG-1_CD4i_R1L14,GACGGACAGCGACGCTCCGG
2176227,CD4i_R1L14,3793,8954.0,0.569578,40.0,TOE1-1,TOE1,ENSG00000132773,targeting,2.893803,targeting single sgRNA,False,TTTGTGAGTTGACCCAAGAGGCAA-1,TTTGTGAGTTGACCCAAGAGGCAA-1_CD4i_R1L14,TACCCACAGACGACTCAGGC
2176228,CD4i_R1L14,3347,6462.0,0.061900,85.0,ZNF397-2,ZNF397,ENSG00000186812,targeting,2.819059,targeting single sgRNA,False,TTTGTGAGTTGCACGCAGTGAGTG-1,TTTGTGAGTTGCACGCAGTGAGTG-1_CD4i_R1L14,GAAGCGACTGGGGAACTCAG
2176229,CD4i_R1L14,4904,14247.0,0.140380,51.0,PPM1A-1,PPM1A,ENSG00000100614,targeting,3.223942,targeting single sgRNA,False,TTTGTGAGTTGCGAAAACAGTCTG-1,TTTGTGAGTTGCGAAAACAGTCTG-1_CD4i_R1L14,GAGCTAGAGAGCAGTGGTCT


In [12]:
# change perturbed_gene_id from categorical to string
cur_data.adata.obs['perturbed_gene_id'] = cur_data.adata.obs['perturbed_gene_id'].astype(str)
cur_data.adata.obs['perturbed_gene_name'] = cur_data.adata.obs['perturbed_gene_name'].astype(str)

cur_data.adata.obs.loc[cur_data.adata.obs['perturbed_gene_id'].isin(['NTC']), 'perturbed_gene_id'] = 'control_nontargeting'
cur_data.adata.obs.loc[cur_data.adata.obs['perturbed_gene_name'].isin(['NTC']), 'perturbed_gene_name'] = 'control_nontargeting'

cur_data.adata.obs.loc[cur_data.adata.obs['perturbed_gene_id'].isna(), 'perturbed_gene_id'] = 'control_casonly'
cur_data.adata.obs.loc[cur_data.adata.obs['perturbed_gene_name'].isna(), 'perturbed_gene_name'] = 'control_casonly'

### Standardise perturbation targets

In [13]:
cur_data.standardize_genes(
    slot='obs',
    input_column='perturbed_gene_id',
    input_column_type='ensembl_gene_id',
    multiple_entries=False,
    # remove_version=True,
    # version_sep='.'
)

Missing Ensembl IDs: ['LUZP6', 'AKAP2', 'ENSG00000182230', 'ENSG00000255823', 'ENSG00000148362', 'U2AF1L5', 'SGK494', 'SEPT6', 'ENSG00000232196', 'OCLM', 'SMIM11B', 'ENSG00000256618', 'ENSG00000277796', 'ENSG00000203812']; attempting to fetch latest IDs...
Fetched latest Ensembl IDs: {'ENSG00000182230': nan, 'ENSG00000255823': nan, 'ENSG00000148362': 'ENSG00000310560', 'ENSG00000232196': nan, 'ENSG00000256618': nan, 'ENSG00000277796': 'ENSG00000293545', 'ENSG00000203812': 'ENSG00000288825'}
--------------------------------------------------
Successfully mapped 12186 out of 12186 Ensembl IDs.
--------------------------------------------------


/homes/zakirov/.local/share/uv/python/cpython-3.12.12-linux-x86_64-gnu/lib/python3.12/functools.py:912: ImplicitModificationWarning: Transforming to str index.
  return dispatch(args[0].__class__)(*args, **kw)


In [14]:
cur_data.adata.obs

,perturbed_gene_name,top_guide_UMI_counts,pct_counts_mt,perturbed_gene_id,PuroR,guide_sequence,lane_id,guide_type,guide_group,low_quality,n_genes_by_counts,perturbation_name,total_counts,guide_id,cell_barcode,perturbed_target_ensg,perturbed_target_symbol,perturbed_target_biotype,perturbed_target_coord,perturbed_target_chromosome,original_index
index,,,,,,,,,,,,,,,,,,,,,
0,NIPAL3,100.0,0.250199,ENSG00000001461,2.410379,GGACTCTTCGTGCAACCCGG,CD4i_R1L13,targeting,targeting single sgRNA,False,3983,AAACAAGCAAACCGGTACTACTCA-1_CD4i_R1L13,8793.0,NIPAL3-1,AAACAAGCAAACCGGTACTACTCA-1,ENSG00000001461,NIPAL3,protein_coding,chr1:24413527-24476735;1,1,0
1,IL12RB2,193.0,0.053763,ENSG00000081985,2.687408,GGCGGAGAGCGCGACACGTG,CD4i_R1L13,targeting,targeting single sgRNA,False,2228,AAACAAGCAAACGGTCAGTGAGTG-1_CD4i_R1L13,3720.0,IL12RB2-2,AAACAAGCAAACGGTCAGTGAGTG-1,ENSG00000081985,IL12RB2,protein_coding,chr1:67307364-67398724;1,1,1
2,control_casonly,NaN,0.252169,control_casonly,0.000000,NaN,CD4i_R1L13,NaN,no sgRNA,False,5695,AAACAAGCAAATAACCACAGTCTG-1_CD4i_R1L13,19828.0,NaN,AAACAAGCAAATAACCACAGTCTG-1,control_casonly,control_casonly,control_casonly,control_casonly,control_casonly,2
3,MCFD2,244.0,0.057977,ENSG00000180398,2.757897,AGGAGCTGCTACAGCAGAGG,CD4i_R1L13,targeting,targeting single sgRNA,False,4152,AAACAAGCAAATAAGGAGTGAGTG-1_CD4i_R1L13,10349.0,MCFD2-1,AAACAAGCAAATAAGGAGTGAGTG-1,ENSG00000180398,MCFD2,protein_coding,chr2:46901870-46941855;-1,2,3
4,ZFAND3,55.0,0.111441,ENSG00000156639,3.068036,GTTCCAGGCCGGTCAGCTGG,CD4i_R1L13,targeting,targeting single sgRNA,False,3925,AAACAAGCAAATACCGACAGTCTG-1_CD4i_R1L13,8076.0,ZFAND3-2,AAACAAGCAAATACCGACAGTCTG-1,ENSG00000156639,ZFAND3,protein_coding,chr6:37819429-38154624;1,6,4
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
2176226,DMRT1,74.0,0.216065,ENSG00000137090,2.744874,GACGGACAGCGACGCTCCGG,CD4i_R1L14,targeting,targeting single sgRNA,False,3637,TTTGTGAGTTGACCCAACAGTCTG-1_CD4i_R1L14,7868.0,DMRT1-2,TTTGTGAGTTGACCCAACAGTCTG-1,ENSG00000137090,DMRT1,protein_coding,chr9:841690-969090;1,9,2176226
2176227,TOE1,40.0,0.569578,ENSG00000132773,2.893803,TACCCACAGACGACTCAGGC,CD4i_R1L14,targeting,targeting single sgRNA,False,3793,TTTGTGAGTTGACCCAAGAGGCAA-1_CD4i_R1L14,8954.0,TOE1-1,TTTGTGAGTTGACCCAAGAGGCAA-1,ENSG00000132773,TOE1,protein_coding,chr1:45340012-45343976;1,1,2176227
2176228,ZNF397,85.0,0.061900,ENSG00000186812,2.819059,GAAGCGACTGGGGAACTCAG,CD4i_R1L14,targeting,targeting single sgRNA,False,3347,TTTGTGAGTTGCACGCAGTGAGTG-1_CD4i_R1L14,6462.0,ZNF397-2,TTTGTGAGTTGCACGCAGTGAGTG-1,ENSG00000186812,ZNF397,protein_coding,chr18:35240508-35267133;1,18,2176228


# Manually replace some genes

In [15]:
# define genes to replace in the cur_data.adata.obs
genes_to_replace = cur_data.adata.obs[cur_data.adata.obs['perturbed_target_symbol'].isna()]['perturbed_gene_name'].drop_duplicates().to_list()
# define columns to replace
cols_to_replace = ['perturbed_target_ensg',	'perturbed_target_symbol',	'perturbed_target_biotype',	'perturbed_target_coord',	'perturbed_target_chromosome']
# define mapping dict for renaming columns in gene_ont for replacement
gene_ont_col_mapping = {
    'ensembl_gene_id':'perturbed_target_ensg',
    'gene_symbol':'perturbed_target_symbol',
    'biotype':'perturbed_target_biotype',
    'gene_coord':'perturbed_target_coord',
    'chromosome_name':'perturbed_target_chromosome'
}
# loop through genes and fill in the missing cols
for replacement_gene in genes_to_replace:
    if replacement_gene in cur_data.gene_ont['synonym'].values:
        # subset gene_ont and get values for replacement
        replacement = (
            cur_data.gene_ont.rename(columns=gene_ont_col_mapping)
            .loc[cur_data.gene_ont['synonym'].isin([replacement_gene]), cols_to_replace]
        )[cols_to_replace].values[0]
        # replace values in cur_data.adata.obs with the values from gene_ont
        cur_data.adata.obs.loc[cur_data.adata.obs['perturbed_gene_name'].isin([replacement_gene]), cols_to_replace] = replacement
        print(f"Replaced {replacement_gene} with {replacement}")
    else:
        print(f"No replacement found for {replacement_gene}")


No replacement found for SMIM11B
No replacement found for MTRNR2L1
Replaced SEPT6 with ['ENSG00000125354' 'SEPTIN6' 'protein_coding'
 'chrX:119615724-119693949;-1' 'X']
Replaced SGK494 with ['ENSG00000167524' 'RSKR' 'protein_coding' 'chr17:28455752-28614197;-1'
 '17']
No replacement found for FAM153B
No replacement found for MTRNR2L4
No replacement found for CCL3L1
No replacement found for OCLM
No replacement found for U2AF1L5
No replacement found for AKAP2
No replacement found for LUZP6
No replacement found for MTRNR2L8


In [16]:
# replace non-mapped perturbed_target_symbol with original gene symbols
cur_data.adata.obs.loc[cur_data.adata.obs['perturbed_target_symbol'].isna(), 'perturbed_target_symbol'] = cur_data.adata.obs.loc[cur_data.adata.obs['perturbed_target_symbol'].isna(), 'perturbed_gene_name'].values

In [17]:
# replace entries in perturbed_target_ensg that are not ENSEMBL ids with NA
cur_data.adata.obs.loc[(~cur_data.adata.obs['perturbed_target_ensg'].str.startswith('ENSG')) & (cur_data.adata.obs['perturbed_target_ensg'] != 'control_nontargeting'), 'perturbed_target_ensg'] = pd.NA

In [18]:
cur_data.adata.obs

,perturbed_gene_name,top_guide_UMI_counts,pct_counts_mt,perturbed_gene_id,PuroR,guide_sequence,lane_id,guide_type,guide_group,low_quality,n_genes_by_counts,perturbation_name,total_counts,guide_id,cell_barcode,perturbed_target_ensg,perturbed_target_symbol,perturbed_target_biotype,perturbed_target_coord,perturbed_target_chromosome,original_index
index,,,,,,,,,,,,,,,,,,,,,
0,NIPAL3,100.0,0.250199,ENSG00000001461,2.410379,GGACTCTTCGTGCAACCCGG,CD4i_R1L13,targeting,targeting single sgRNA,False,3983,AAACAAGCAAACCGGTACTACTCA-1_CD4i_R1L13,8793.0,NIPAL3-1,AAACAAGCAAACCGGTACTACTCA-1,ENSG00000001461,NIPAL3,protein_coding,chr1:24413527-24476735;1,1,0
1,IL12RB2,193.0,0.053763,ENSG00000081985,2.687408,GGCGGAGAGCGCGACACGTG,CD4i_R1L13,targeting,targeting single sgRNA,False,2228,AAACAAGCAAACGGTCAGTGAGTG-1_CD4i_R1L13,3720.0,IL12RB2-2,AAACAAGCAAACGGTCAGTGAGTG-1,ENSG00000081985,IL12RB2,protein_coding,chr1:67307364-67398724;1,1,1
2,control_casonly,NaN,0.252169,control_casonly,0.000000,NaN,CD4i_R1L13,NaN,no sgRNA,False,5695,AAACAAGCAAATAACCACAGTCTG-1_CD4i_R1L13,19828.0,NaN,AAACAAGCAAATAACCACAGTCTG-1,NaN,control_casonly,control_casonly,control_casonly,control_casonly,2
3,MCFD2,244.0,0.057977,ENSG00000180398,2.757897,AGGAGCTGCTACAGCAGAGG,CD4i_R1L13,targeting,targeting single sgRNA,False,4152,AAACAAGCAAATAAGGAGTGAGTG-1_CD4i_R1L13,10349.0,MCFD2-1,AAACAAGCAAATAAGGAGTGAGTG-1,ENSG00000180398,MCFD2,protein_coding,chr2:46901870-46941855;-1,2,3
4,ZFAND3,55.0,0.111441,ENSG00000156639,3.068036,GTTCCAGGCCGGTCAGCTGG,CD4i_R1L13,targeting,targeting single sgRNA,False,3925,AAACAAGCAAATACCGACAGTCTG-1_CD4i_R1L13,8076.0,ZFAND3-2,AAACAAGCAAATACCGACAGTCTG-1,ENSG00000156639,ZFAND3,protein_coding,chr6:37819429-38154624;1,6,4
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
2176226,DMRT1,74.0,0.216065,ENSG00000137090,2.744874,GACGGACAGCGACGCTCCGG,CD4i_R1L14,targeting,targeting single sgRNA,False,3637,TTTGTGAGTTGACCCAACAGTCTG-1_CD4i_R1L14,7868.0,DMRT1-2,TTTGTGAGTTGACCCAACAGTCTG-1,ENSG00000137090,DMRT1,protein_coding,chr9:841690-969090;1,9,2176226
2176227,TOE1,40.0,0.569578,ENSG00000132773,2.893803,TACCCACAGACGACTCAGGC,CD4i_R1L14,targeting,targeting single sgRNA,False,3793,TTTGTGAGTTGACCCAAGAGGCAA-1_CD4i_R1L14,8954.0,TOE1-1,TTTGTGAGTTGACCCAAGAGGCAA-1,ENSG00000132773,TOE1,protein_coding,chr1:45340012-45343976;1,1,2176227
2176228,ZNF397,85.0,0.061900,ENSG00000186812,2.819059,GAAGCGACTGGGGAACTCAG,CD4i_R1L14,targeting,targeting single sgRNA,False,3347,TTTGTGAGTTGCACGCAGTGAGTG-1_CD4i_R1L14,6462.0,ZNF397-2,TTTGTGAGTTGCACGCAGTGAGTG-1,ENSG00000186812,ZNF397,protein_coding,chr18:35240508-35267133;1,18,2176228


### Add `perturbed_target_number` column

In [19]:
# cur_data.count_entries(
#     slot='obs',
#     input_column='perturbed_target_ensg',
#     count_column_name='perturbed_target_number',
#     sep='|'
# )
cur_data.adata.obs['perturbed_target_number'] = 1

### Encode chromosomes as integers

In [20]:
cur_data.chromosome_encoding()

Chromosome encoding applied to perturbed_target_chromosome in adata.obs and stored as 'perturbed_target_chromosome_encoding'.


In [21]:
cur_data.adata.obs[['perturbation_name', 'perturbed_target_chromosome_encoding']]

,perturbation_name,perturbed_target_chromosome_encoding
index,,
0,AAACAAGCAAACCGGTACTACTCA-1_CD4i_R1L13,1
1,AAACAAGCAAACGGTCAGTGAGTG-1_CD4i_R1L13,1
2,AAACAAGCAAATAACCACAGTCTG-1_CD4i_R1L13,0
3,AAACAAGCAAATAAGGAGTGAGTG-1_CD4i_R1L13,2
4,AAACAAGCAAATACCGACAGTCTG-1_CD4i_R1L13,6
...,...,...
2176226,TTTGTGAGTTGACCCAACAGTCTG-1_CD4i_R1L14,9
2176227,TTTGTGAGTTGACCCAAGAGGCAA-1_CD4i_R1L14,1
2176228,TTTGTGAGTTGCACGCAGTGAGTG-1_CD4i_R1L14,18


In [22]:
cur_data.adata.obs

,perturbed_gene_name,top_guide_UMI_counts,pct_counts_mt,perturbed_gene_id,PuroR,guide_sequence,lane_id,guide_type,guide_group,low_quality,n_genes_by_counts,perturbation_name,total_counts,guide_id,cell_barcode,perturbed_target_ensg,perturbed_target_symbol,perturbed_target_biotype,perturbed_target_coord,perturbed_target_chromosome,original_index,perturbed_target_number,perturbed_target_chromosome_encoding
index,,,,,,,,,,,,,,,,,,,,,,,
0,NIPAL3,100.0,0.250199,ENSG00000001461,2.410379,GGACTCTTCGTGCAACCCGG,CD4i_R1L13,targeting,targeting single sgRNA,False,3983,AAACAAGCAAACCGGTACTACTCA-1_CD4i_R1L13,8793.0,NIPAL3-1,AAACAAGCAAACCGGTACTACTCA-1,ENSG00000001461,NIPAL3,protein_coding,chr1:24413527-24476735;1,1,0,1,1
1,IL12RB2,193.0,0.053763,ENSG00000081985,2.687408,GGCGGAGAGCGCGACACGTG,CD4i_R1L13,targeting,targeting single sgRNA,False,2228,AAACAAGCAAACGGTCAGTGAGTG-1_CD4i_R1L13,3720.0,IL12RB2-2,AAACAAGCAAACGGTCAGTGAGTG-1,ENSG00000081985,IL12RB2,protein_coding,chr1:67307364-67398724;1,1,1,1,1
2,control_casonly,NaN,0.252169,control_casonly,0.000000,NaN,CD4i_R1L13,NaN,no sgRNA,False,5695,AAACAAGCAAATAACCACAGTCTG-1_CD4i_R1L13,19828.0,NaN,AAACAAGCAAATAACCACAGTCTG-1,NaN,control_casonly,control_casonly,control_casonly,control_casonly,2,1,0
3,MCFD2,244.0,0.057977,ENSG00000180398,2.757897,AGGAGCTGCTACAGCAGAGG,CD4i_R1L13,targeting,targeting single sgRNA,False,4152,AAACAAGCAAATAAGGAGTGAGTG-1_CD4i_R1L13,10349.0,MCFD2-1,AAACAAGCAAATAAGGAGTGAGTG-1,ENSG00000180398,MCFD2,protein_coding,chr2:46901870-46941855;-1,2,3,1,2
4,ZFAND3,55.0,0.111441,ENSG00000156639,3.068036,GTTCCAGGCCGGTCAGCTGG,CD4i_R1L13,targeting,targeting single sgRNA,False,3925,AAACAAGCAAATACCGACAGTCTG-1_CD4i_R1L13,8076.0,ZFAND3-2,AAACAAGCAAATACCGACAGTCTG-1,ENSG00000156639,ZFAND3,protein_coding,chr6:37819429-38154624;1,6,4,1,6
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
2176226,DMRT1,74.0,0.216065,ENSG00000137090,2.744874,GACGGACAGCGACGCTCCGG,CD4i_R1L14,targeting,targeting single sgRNA,False,3637,TTTGTGAGTTGACCCAACAGTCTG-1_CD4i_R1L14,7868.0,DMRT1-2,TTTGTGAGTTGACCCAACAGTCTG-1,ENSG00000137090,DMRT1,protein_coding,chr9:841690-969090;1,9,2176226,1,9
2176227,TOE1,40.0,0.569578,ENSG00000132773,2.893803,TACCCACAGACGACTCAGGC,CD4i_R1L14,targeting,targeting single sgRNA,False,3793,TTTGTGAGTTGACCCAAGAGGCAA-1_CD4i_R1L14,8954.0,TOE1-1,TTTGTGAGTTGACCCAAGAGGCAA-1,ENSG00000132773,TOE1,protein_coding,chr1:45340012-45343976;1,1,2176227,1,1
2176228,ZNF397,85.0,0.061900,ENSG00000186812,2.819059,GAAGCGACTGGGGAACTCAG,CD4i_R1L14,targeting,targeting single sgRNA,False,3347,TTTGTGAGTTGCACGCAGTGAGTG-1_CD4i_R1L14,6462.0,ZNF397-2,TTTGTGAGTTGCACGCAGTGAGTG-1,ENSG00000186812,ZNF397,protein_coding,chr18:35240508-35267133;1,18,2176228,1,18


### Curate replicates

In [23]:
cur_data.adata.obs = cur_data.adata.obs.rename(columns={'lane_id':'technical_replicate'})

### Add metadata

In [24]:
cur_data.create_columns(
    overwrite=True,
    slot="obs",
    col_dict={
        "dataset_id": cur_data.dataset_id,
        "sample_id": range(1, cur_data.adata.obs.shape[0] + 1),
        # perturbation type
        "perturbation_type_label": "CRISPRi",
        "perturbation_type_id": None,
        "data_modality": "Perturb-seq",
        "significant": None,
        "significance_criteria": None,
        "score_interpretation": None,

        # treatment
        "treatment_label": "anti-CD3 antibody|anti-CD28 antibody|anti-CD2 antibody",
        "treatment_id": "EFO:0003317|EFO:0003304|NCIT:C184729",
        # replicates
        # "technical_replicate": None,
        "biological_replicate": "D3_CE0008678",
        # model system
        "model_system_label": "primary_cell",
        "model_system_id": None,
        "tissue": "lymphoid tissue",
        "cell_line_label": None,
        "cell_line_id": None,
        "cell_type_label": "CD4-positive, alpha-beta T cell",
        "disease_label": "healthy",
        "disease_id": None,

        "timepoint": "P12DT8H0M0S",
        "species": "Homo sapiens",
        "sex_label": "female",
        "sex_id": None,
        "developmental_stage_label": "adult",
        "developmental_stage_id": None,

        "study_title": "Genome-scale perturb-seq in primary human CD4+ T cells maps context-specific regulators of T cell programs and human immune traits",
        "study_uri": "https://doi.org/10.64898/2025.12.23.696273",
        "study_year": 2025,
        "first_author": "Ronghui Zhu",
        "last_author": "Alexander Marson",

        "experiment_title": "Perturb-seq of primary human CD4-positive T cells for patient D3_CE0008678, stimulated for 8hr with ImmunoCult CD3/CD28/CD2 activator",
        "experiment_summary": """
            Isolated human CD4-positive cells from four healthy donors were stimulated with ImmunoCult CD3/CD28/CD2 activator and sequentially transduced with dCas9-KRAB-Zim3 lentivirus (next morning after stimulation) and a Perturb-seq guide library (next afternoon after stimulation, MOI 0.2).
            The library consisted all genes expressed in human CD4+ T cells, all transcription factors annotated in the Lambert et al. (2018) and non-targeting controls totalling 12,748 genes.
            The gRNA sequences were selected from hCRISPRiv2 and Dolcetto libraries.
            On day 12, cells were split into three conditions:
            (1) Rest - cells were left for 8 hr without stimulation;
            (2) Stim8hr - cells were stimulated with ImmunoCult CD3/CD28/CD2 activator for 8 hr;
            (3) Stim48hr - cells were stimulated with ImmunoCult CD3/CD28/CD2 activator for 48 hr.
            Cells were harvested, fixed, stored using GEM-X Flex Sample Preparation v2 Kit and sequenced using GEM-X Flex Gene Expression Human n-plex kit converted into Ultima compatible libraries for sequencing on the Ultima Genomics UG100.
            """,

        "number_of_perturbed_targets": len(set(cur_data.adata.obs['perturbed_target_symbol'])),
        "number_of_perturbed_samples": cur_data.adata.obs.shape[0],

        "library_generation_type_id": "EFO:0022868",
        "library_generation_type_label": "endogenous",

        "library_generation_method_id": None,
        "library_generation_method_label": "dCas9-KRAB-Zim3",

        "enzyme_delivery_method_id": None,
        "enzyme_delivery_method_label": "lentivirus transduction",

        "library_delivery_method_id": None,
        "library_delivery_method_label": "lentivirus transduction",

        "enzyme_integration_state_id": None,
        "enzyme_integration_state_label": "random locus integration",

        "library_integration_state_id": None,
        "library_integration_state_label": "random locus integration",

        "enzyme_expression_control_id": None,
        "enzyme_expression_control_label": "constitutive transgene expression",

        "library_expression_control_id": None,
        "library_expression_control_label": "constitutive transgene expression",

        "library_name": "custom",
        "library_uri": None,

        "library_format_id": None,
        "library_format_label": "pooled",

        "library_scope_id": None,
        "library_scope_label": "focused",

        "library_perturbation_type_id": None,
        "library_perturbation_type_label": "inhibition",

        "library_manufacturer": "Marson lab",
        "library_lentiviral_generation": "2",
        "library_grnas_per_target": "2",
        "library_total_grnas": str(cur_data.adata.obs['guide_sequence'].str.split('|').explode().nunique()),
        "library_total_variants": None,

        "readout_dimensionality_id": None,
        "readout_dimensionality_label": "high-dimensional assay",

        "readout_type_id": None,
        "readout_type_label": "transcriptomic",

        "readout_technology_id": None,
        "readout_technology_label": "single-cell rna-seq",

        "method_name_id": None,
        "method_name_label": "Perturb-seq",

        "method_uri": None,

        "sequencing_library_kit_id": None,
        "sequencing_library_kit_label": "GEM-X Flex Gene Expression Human n-plex kit",

        "sequencing_platform_id": None,
        "sequencing_platform_label": "Ultima Genomics UG100",

        "sequencing_strategy_id": None,
        "sequencing_strategy_label": "barcode sequencing",

        "software_counts_id": None,
        "software_counts_label": "CellRanger",

        "software_analysis_id": None,
        "software_analysis_label": "scanpy",

        "reference_genome_id": None,
        "reference_genome_label": "GRCh38",

        "license_label": "MIT License",
        "license_id": "SWO:9000074",

        "associated_datasets": json.dumps([
            {
                "dataset_accession": "Primary Human CD4+ T Cell Perturb-seq",
                "dataset_uri": "s3://genome-scale-tcell-perturb-seq/marson2025_data/D3_Stim8hr.assigned_guide.h5ad",
                "dataset_description": "Cell expression profiles for cells from donor D3_CE0008678, stimulated for 8hr with ImmunoCult CD3/CD28/CD2 activator.",
                "dataset_file_name": "D3_Stim8hr.assigned_guide.h5ad",
            }
        ])
    }
)

Column dataset_id added to adata.obs
Column sample_id added to adata.obs
Column perturbation_type_label added to adata.obs
Column perturbation_type_id added to adata.obs
Column data_modality added to adata.obs
Column significant added to adata.obs
Column significance_criteria added to adata.obs
Column score_interpretation added to adata.obs
Column treatment_label added to adata.obs
Column treatment_id added to adata.obs
Column biological_replicate added to adata.obs
Column model_system_label added to adata.obs
Column model_system_id added to adata.obs
Column tissue added to adata.obs
Column cell_line_label added to adata.obs
Column cell_line_id added to adata.obs
Column cell_type_label added to adata.obs
Column disease_label added to adata.obs
Column disease_id added to adata.obs
Column timepoint added to adata.obs
Column species added to adata.obs
Column sex_label added to adata.obs
Column sex_id added to adata.obs
Column developmental_stage_label added to adata.obs
Column development

In [25]:
cur_data.adata.obs

,perturbed_gene_name,top_guide_UMI_counts,pct_counts_mt,perturbed_gene_id,PuroR,guide_sequence,technical_replicate,guide_type,guide_group,low_quality,n_genes_by_counts,perturbation_name,total_counts,guide_id,cell_barcode,perturbed_target_ensg,perturbed_target_symbol,perturbed_target_biotype,perturbed_target_coord,perturbed_target_chromosome,original_index,perturbed_target_number,perturbed_target_chromosome_encoding,dataset_id,sample_id,perturbation_type_label,perturbation_type_id,data_modality,significant,significance_criteria,score_interpretation,treatment_label,treatment_id,biological_replicate,model_system_label,model_system_id,tissue,cell_line_label,cell_line_id,cell_type_label,disease_label,disease_id,timepoint,species,sex_label,sex_id,developmental_stage_label,developmental_stage_id,study_title,study_uri,study_year,first_author,last_author,experiment_title,experiment_summary,number_of_perturbed_targets,number_of_perturbed_samples,library_generation_type_id,library_generation_type_label,library_generation_method_id,library_generation_method_label,enzyme_delivery_method_id,enzyme_delivery_method_label,library_delivery_method_id,library_delivery_method_label,enzyme_integration_state_id,enzyme_integration_state_label,library_integration_state_id,library_integration_state_label,enzyme_expression_control_id,enzyme_expression_control_label,library_expression_control_id,library_expression_control_label,library_name,library_uri,library_format_id,library_format_label,library_scope_id,library_scope_label,library_perturbation_type_id,library_perturbation_type_label,library_manufacturer,library_lentiviral_generation,library_grnas_per_target,library_total_grnas,library_total_variants,readout_dimensionality_id,readout_dimensionality_label,readout_type_id,readout_type_label,readout_technology_id,readout_technology_label,method_name_id,method_name_label,method_uri,sequencing_library_kit_id,sequencing_library_kit_label,sequencing_platform_id,sequencing_platform_label,sequencing_strategy_id,sequencing_strategy_label,software_counts_id,software_counts_label,software_analysis_id,software_analysis_label,reference_genome_id,reference_genome_label,license_label,license_id,associated_datasets
index,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,,
0,NIPAL3,100.0,0.250199,ENSG00000001461,2.410379,GGACTCTTCGTGCAACCCGG,CD4i_R1L13,targeting,targeting single sgRNA,False,3983,AAACAAGCAAACCGGTACTACTCA-1_CD4i_R1L13,8793.0,NIPAL3-1,AAACAAGCAAACCGGTACTACTCA-1,ENSG00000001461,NIPAL3,protein_coding,chr1:24413527-24476735;1,1,0,1,1,zhu_2025_D1_stim8hr_cl,1,CRISPRi,None,Perturb-seq,None,None,None,anti-CD3 antibody|anti-CD28 antibody|anti-CD2 ...,EFO:0003317|EFO:0003304|NCIT:C184729,D1_CE0008162,primary_cell,None,lymphoid tissue,None,None,"CD4-positive, alpha-beta T cell",healthy,None,P12DT8H0M0S,Homo sapiens,female,None,adult,None,Genome-scale perturb-seq in primary human CD4+...,https://doi.org/10.64898/2025.12.23.696273,2025,Ronghui Zhu,Alexander Marson,Perturb-seq of primary human CD4-positive T ce...,\n Isolated human CD4-positive cell...,12186,2176231,EFO:0022868,endogenous,None,dCas9-KRAB-Zim3,None,lentivirus transduction,None,lentivirus transduction,None,random locus integration,None,random locus integration,None,constitutive transgene expression,None,constitutive transgene expression,custom,None,None,pooled,None,focused,None,inhibition,Marson lab,2,2,23847,None,None,high-dimensional assay,None,transcriptomic,None,single-cell rna-seq,None,Perturb-seq,None,None,GEM-X Flex Gene Expression Human n-plex kit,None,Ultima Genomics UG100,None,barcode sequencing,None,CellRanger,None,scanpy,None,GRCh38,MIT License,SWO:9000074,"[{""dataset_accession"": ""Primary Human CD4+ T C..."
1,IL12RB2,193.0,0.053763,ENSG00000081985,2.687408,GGCGGAGAGCGCGACACGTG,CD4i_R1L13,targeting,targeting single sgRNA,False,2228,AAACAAGCAAACGGTCAGTGAGTG-1_CD4i_R1L13,3720.0,IL12RB2-2,AAACAAGCAAACGGTCAGTGAGTG-1,ENSG00000081985,IL1

### Curate tissue information


In [26]:
cur_data.standardize_ontology(
    input_column='tissue',
    column_type='term_name',
    ontology_type='tissue',
    overwrite=True
)

Mapped 1 tissue ontology terms from `tissue` column to ontology terms
DataFrame shape: (1, 4)
--------------------------------------------------
      input_column input_column_lower       name_lower     ontology_id
0  lymphoid tissue    lymphoid tissue  lymphoid tissue  UBERON:0001744
--------------------------------------------------


/homes/zakirov/.local/share/uv/python/cpython-3.12.12-linux-x86_64-gnu/lib/python3.12/functools.py:912: ImplicitModificationWarning: Transforming to str index.
  return dispatch(args[0].__class__)(*args, **kw)


### Curate cell type information

In [27]:
cur_data.standardize_ontology(
    input_column='cell_type_label',
    column_type='term_name',
    ontology_type='cell_type',
    overwrite=True
)

Mapped 1 cell_type ontology terms from `cell_type_label` column to ontology terms
DataFrame shape: (1, 4)
--------------------------------------------------
                      input_column               input_column_lower  \
0  CD4-positive, alpha-beta T cell  cd4-positive, alpha-beta t cell   

                        name_lower ontology_id  
0  cd4-positive, alpha-beta t cell  CL:0000624  
--------------------------------------------------
Overwriting column cell_type_label in adata.obs


/homes/zakirov/.local/share/uv/python/cpython-3.12.12-linux-x86_64-gnu/lib/python3.12/functools.py:912: ImplicitModificationWarning: Transforming to str index.
  return dispatch(args[0].__class__)(*args, **kw)


### Curate disease information

In [28]:
cur_data.standardize_ontology(
    input_column='disease_label',
    column_type='term_name',
    ontology_type='disease',
    overwrite=True
)

### Match schema column order

In [29]:
cur_data.match_schema_columns(slot='obs')

Matched columns of adata.obs to the obs_schema.


### Validate obs metadata

In [30]:
cur_data.validate_data(slot='obs', verbose=True)

2026-02-16 09:37:38,790 INFO curation_tools.curation_tools: adata.obs is valid according to the obs_schema.


,dataset_id,sample_id,data_modality,significant,significance_criteria,perturbation_name,perturbed_target_coord,perturbed_target_chromosome,perturbed_target_chromosome_encoding,perturbed_target_number,perturbed_target_ensg,perturbed_target_symbol,perturbed_target_biotype,guide_sequence,perturbation_type_label,perturbation_type_id,timepoint,treatment_label,treatment_id,technical_replicate,biological_replicate,model_system_label,model_system_id,species,tissue_label,tissue_id,cell_type_label,cell_type_id,cell_line_label,cell_line_id,sex_label,sex_id,developmental_stage_label,developmental_stage_id,disease_label,disease_id,study_title,study_uri,study_year,first_author,last_author,experiment_title,experiment_summary,number_of_perturbed_targets,number_of_perturbed_samples,library_generation_type_id,library_generation_type_label,library_generation_method_id,library_generation_method_label,enzyme_delivery_method_id,enzyme_delivery_method_label,library_delivery_method_id,library_delivery_method_label,enzyme_integration_state_id,enzyme_integration_state_label,library_integration_state_id,library_integration_state_label,enzyme_expression_control_id,enzyme_expression_control_label,library_expression_control_id,library_expression_control_label,library_name,library_uri,library_format_id,library_format_label,library_scope_id,library_scope_label,library_perturbation_type_id,library_perturbation_type_label,library_manufacturer,library_lentiviral_generation,library_grnas_per_target,library_total_grnas,library_total_variants,readout_dimensionality_id,readout_dimensionality_label,readout_type_id,readout_type_label,readout_technology_id,readout_technology_label,method_name_id,method_name_label,method_uri,sequencing_library_kit_id,sequencing_library_kit_label,sequencing_platform_id,sequencing_platform_label,sequencing_strategy_id,sequencing_strategy_label,software_counts_id,software_counts_label,software_analysis_id,software_analysis_label,score_interpretation,reference_genome_id,reference_genome_label,associated_datasets,license_label,license_id
0,zhu_2025_D1_stim8hr_cl,1,Perturb-seq,<NA>,<NA>,AAACAAGCAAACCGGTACTACTCA-1_CD4i_R1L13,chr1:24413527-24476735;1,1,1,1,ENSG00000001461,NIPAL3,protein_coding,GGACTCTTCGTGCAACCCGG,CRISPRi,<NA>,P12DT8H0M0S,anti-CD3 antibody|anti-CD28 antibody|anti-CD2 ...,EFO:0003317|EFO:0003304|NCIT:C184729,CD4i_R1L13,D1_CE0008162,primary_cell,<NA>,Homo sapiens,lymphoid tissue,UBERON:0001744,"CD4-positive, alpha-beta T cell",CL:0000624,<NA>,<NA>,female,<NA>,adult,<NA>,healthy,<NA>,Genome-scale perturb-seq in primary human CD4+...,https://doi.org/10.64898/2025.12.23.696273,2025,Ronghui Zhu,Alexander Marson,Perturb-seq of primary human CD4-positive T ce...,\n Isolated human CD4-positive cell...,12186,2176231,EFO:0022868,endogenous,<NA>,dCas9-KRAB-Zim3,<NA>,lentivirus transduction,<NA>,lentivirus transduction,<NA>,random locus integration,<NA>,random locus integration,<NA>,constitutive transgene expression,<NA>,constitutive transgene expression,custom,<NA>,<NA>,pooled,<NA>,focused,<NA>,inhibition,Marson lab,2,2,23847,<NA>,<NA>,high-dimensional assay,<NA>,transcriptomic,<NA>,single-cell rna-seq,<NA>,Perturb-seq,<NA>,<NA>,GEM-X Flex Gene Expression Human n-plex kit,<NA>,Ultima Genomics UG100,<NA>,barcode sequencing,<NA>,CellRanger,<NA>,scanpy,<NA>,<NA>,GRCh38,"[{""dataset_accession"": ""Primary Human CD4+ T C...",MIT License,SWO:9000074
1,zhu_2025_D1_stim8hr_cl,2,Perturb-seq,<NA>,<NA>,AAACAAGCAAACGGTCAGTGAGTG-1_CD4i_R1L13,chr1:67307364-67398724;1,1,1,1,ENSG00000081985,IL12RB2,protein_coding,GGCGGAGAGCGCGACACGTG,CRISPRi,<NA>,P12DT8H0M0S,anti-CD3 antibody|anti-CD28 antibody|anti-CD2 ...,EFO:0003317|EFO:0003304|NCIT:C184729,CD4i_R1L13,D1_CE0008162,primary_cell,<NA>,Homo sapiens,lymphoid tissue,UBERON:0001744,"CD4-positive, alpha-beta T cell",CL:0000624,<NA>,<NA>,female,<NA>,adult,<NA>,healthy,<NA>,Genome-scale perturb-seq in primary human CD4+...,https://doi.org/10.64898/2025.12.23.696273,2025,Ronghui Zhu,Alexander Marson,Perturb-seq 

# VAR slot curation

### Standardise genes

In [31]:
cur_data.adata.var

,gene_ids,feature_types,genome,gene_name,mt
ENSG00000000003,ENSG00000000003,Gene Expression,GRCh38,TSPAN6,False
ENSG00000000005,ENSG00000000005,Gene Expression,GRCh38,TNMD,False
ENSG00000000419,ENSG00000000419,Gene Expression,GRCh38,DPM1,False
ENSG00000000457,ENSG00000000457,Gene Expression,GRCh38,SCYL3,False
ENSG00000000460,ENSG00000000460,Gene Expression,GRCh38,C1orf112,False
...,...,...,...,...,...
ENSG00000291122,ENSG00000291122,Gene Expression,GRCh38,CASTOR3P,False
ENSG00000291135,ENSG00000291135,Gene Expression,GRCh38,FCGR1BP,False
ENSG00000291145,ENSG00000291145,Gene Expression,GRCh38,PPP5D1P,False
ENSG00000291237,ENSG00000291237,Gene Expression,GRCh38,SOD2,False


In [32]:
cur_data.standardize_genes(
    slot="var",
    input_column="gene_ids",
    input_column_type="ensembl_gene_id",
    remove_version=False,
    multiple_entries=False
)

Missing Ensembl IDs: ['CUSTOM001_PuroR', 'ENSG00000148362', 'ENSG00000139656']; attempting to fetch latest IDs...
Fetched latest Ensembl IDs: {'ENSG00000148362': 'ENSG00000310560', 'ENSG00000139656': 'ENSG00000226519'}
--------------------------------------------------
Successfully mapped 18130 out of 18130 Ensembl IDs.
--------------------------------------------------


/homes/zakirov/.local/share/uv/python/cpython-3.12.12-linux-x86_64-gnu/lib/python3.12/functools.py:912: ImplicitModificationWarning: Transforming to str index.
  return dispatch(args[0].__class__)(*args, **kw)


In [33]:
# replace gene symbols that are NOT ENSG with original provided gene symbol
cur_data.adata.var.loc[(cur_data.adata.var['gene_symbol'].isna()) &
 (~cur_data.adata.var['gene_name'].str.startswith('ENSG')), 'gene_symbol'] = cur_data.adata.var.loc[(cur_data.adata.var['gene_symbol'].isna()) &
 (~cur_data.adata.var['gene_name'].str.startswith('ENSG')), 'gene_name']

In [34]:
cur_data.adata.var.loc[cur_data.adata.var['ensembl_gene_id'] == 'CUSTOM001_PuroR', 'ensembl_gene_id'] = None

### Validate var metadata

In [35]:
cur_data.validate_data(slot='var')

2026-02-16 09:37:39,828 INFO curation_tools.curation_tools: adata.var is valid according to the var_schema.


,ensembl_gene_id,gene_symbol
index,,
0,ENSG00000000003,TSPAN6
1,ENSG00000000005,TNMD
2,ENSG00000000419,DPM1
3,ENSG00000000457,SCYL3
4,ENSG00000000460,FIRRM
...,...,...
18125,ENSG00000291122,CASTOR3P
18126,ENSG00000291135,FCGR1BP
18127,ENSG00000291145,PPP5D1P


# Save the dataset

In [56]:
cur_data.save_curated_data_h5ad()

✅ Curated h5ad data saved to ../curated/h5ad/zhu_2025_D1_stim8hr_cl_curated.h5ad


In [57]:
cur_data.save_curated_data_parquet(split_metadata=True, save_metadata_only=True)

✅ Metadata saved to ../curated/parquet/zhu_2025_D1_stim8hr_cl_curated_metadata.parquet


# Upload to BigQuery

In [95]:
# upload_parquet_to_bq(
#     parquet_path='../curated/parquet/zhu_2025_D1_rest_cl_curated_metadata.parquet',
#     bq_dataset_id='prj-ext-dev-pertcat-437314.perturb_seq',
#     bq_table_name='metadata',
#     key_columns=['dataset_id', 'sample_id'],
#     verbose=True
# )

# Upload to GC Storage

In [59]:
# !gcloud storage cp ../curated/h5ad/zhu_2025_D3_stim8hr_cl_curated.h5ad gs://perturbation-catalogue-lake/perturbseq/curated/

/bin/sh: line 1: gcloud: command not found
